In [ ]:
!pip install -q -U diffusers transformers accelerate huggingface_hub pandas==2.2.3

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 12.3/12.3 MB 57.4 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 394.3/394.3 kB 22.3 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 846.4/846.4 kB 35.7 MB/s eta 0:00:00


In [ ]:
import os
import logging
from google.colab import drive

# 1. Configure logging
logging.basicConfig(level=logging.INFO, format="%(asctime)s [%(levelname)s] %(message)s", force=True)
logger = logging.getLogger(__name__)

# 2. Mount Google Drive
drive.mount('/content/drive')

# 3.  INPUT Directory
INPUT_DIR = "/content/drive/MyDrive/frugalAi"
IMAGES_DIR = os.path.join(INPUT_DIR, "generated_portraits_hashed")
CSV_PATH = os.path.join(INPUT_DIR, "sampled_dataset.csv")

if not os.path.exists(CSV_PATH):
    raise FileNotFoundError(f"Could not find CSV at {CSV_PATH}")
assert os.path.exists(IMAGES_DIR), f"Images directory is missing at {IMAGES_DIR}!"

logger.info(f"Using CSV from: {CSV_PATH}")
logger.info(f"Looking for images in: {IMAGES_DIR}")

# 4.  OUTPUT Directory
OUTPUT_BASE_DIR = "/content/drive/MyDrive/Frugal AI Project"

if not os.path.exists(OUTPUT_BASE_DIR):
    raise FileNotFoundError(f"Cannot find {OUTPUT_BASE_DIR}. Ensure you added a shortcut to it in your 'My Drive'!")

# 5.  Output Paths
ACCESSORY_TYPE = "mask"
OUTPUT_IMAGES_DIR = os.path.join(OUTPUT_BASE_DIR, f"generated_{ACCESSORY_TYPE}s")
OUTPUT_CSV = os.path.join(OUTPUT_BASE_DIR, f"sampled_dataset_{ACCESSORY_TYPE}s.csv")
CHECKPOINT_FILE = os.path.join(OUTPUT_BASE_DIR, f"checkpoint_{ACCESSORY_TYPE}.txt")

# Create output directory
os.makedirs(OUTPUT_IMAGES_DIR, exist_ok=True)
logger.info(f"Outputs will be saved to: {OUTPUT_IMAGES_DIR}")

Mounted at /content/drive


2026-09-25 22:00:18,454 [INFO] Using CSV from: /content/drive/MyDrive/frugalAi/sampled_dataset.csv
2026-09-25 22:00:18,454 [INFO] Looking for images in: /content/drive/MyDrive/frugalAi/generated_portraits_hashed
2026-09-25 22:00:19,192 [INFO] Outputs will be saved to: /content/drive/MyDrive/Frugal AI Project/generated_masks


## Load the Sampled Dataset and Checkpoints
Load the 720 filtered identities and determine our starting index in case of a previous interruption.

In [ ]:
import pandas as pd

df = pd.read_csv(CSV_PATH)
logger.info(f"Loaded {len(df):,} rows from sample dataset.")

# Initialize the output CSV if it doesn't exist
if not os.path.exists(OUTPUT_CSV):
    out_df = df.copy().head(0)
    out_df["ACCESSORY"] = ""
    out_df.to_csv(OUTPUT_CSV, index=False)
    logger.info("Created new output tracker.")

# Read checkpoint to resume
START_INDEX = 0
if os.path.exists(CHECKPOINT_FILE):
    with open(CHECKPOINT_FILE, "r") as f:
        content = f.read().strip()
        if content.isdigit():
            START_INDEX = int(content) + 1
            logger.info(f"Found checkpoint. Resuming run from index {START_INDEX}.")

if START_INDEX >= len(df):
    logger.info("All images have already been processed.")

2026-09-25 13:24:05,893 [INFO] Loaded 720 rows from sample dataset.
2026-09-25 13:24:05,904 [INFO] Created new output tracker.


## Load FLUX.2 [Klein] Pipeline
Loading the designated bfloat16 model with CPU offloading to optimize memory on the A100.

In [ ]:
from diffusers import Flux2KleinPipeline

if START_INDEX < len(df):
    logger.info("Loading FLUX.2 pipeline...")
    pipe = Flux2KleinPipeline.from_pretrained(
        "black-forest-labs/FLUX.2-klein-base-4B",
        torch_dtype=torch.bfloat16,
    )
    pipe.enable_model_cpu_offload()
    logger.info("Pipeline successfully loaded.")

2026-09-25 12:28:08,180 [INFO] Loading FLUX.2 pipeline...
/usr/local/lib/python3.13/dist-packages/diffusers/utils/deprecation_utils.py:23: FutureWarning: `torch_dtype` is deprecated and will be removed in version 1.0.0. Please use `dtype` instead.
  deprecate("torch_dtype", "1.0.0", _TORCH_DTYPE_DEPRECATION_MESSAGE)
2026-09-25 12:28:08,990 [INFO] HTTP Request: GET https://huggingface.co/api/agent-harnesses "HTTP/1.1 200 OK"
2026-09-25 12:28:09,081 [INFO] HTTP Request: GET https://huggingface.co/api/models/black-forest-labs/FLUX.2-klein-base-4B "HTTP/1.1 200 OK"
2026-09-25 12:28:09,169 [INFO] HTTP Request: HEAD https://huggingface.co/black-forest-labs/FLUX.2-klein-base-4B/resolve/main/model_index.json "HTTP/1.1 307 Temporary Redirect"
2026-09-25 12:28:09,181 [INFO] HTTP Request: HEAD https://huggingface.co/api/resolve-cache/models/black-forest-labs/FLUX.2-klein-base-4B/a3b4f4849157f664bdbc776fd7453c2783562f4d/model_index.json "HTTP/1.1 200 OK"
2026-09-25 12:28:09,196 [INFO] HTTP Request

model_index.json:   0%|          | 0.00/422 [00:00<?, ?B/s]

2026-09-25 12:28:09,301 [INFO] HTTP Request: GET https://huggingface.co/api/models/black-forest-labs/FLUX.2-klein-base-4B/revision/main "HTTP/1.1 200 OK"
2026-09-25 12:28:09,394 [INFO] HTTP Request: GET https://huggingface.co/api/models/black-forest-labs/FLUX.2-klein-base-4B/tree/a3b4f4849157f664bdbc776fd7453c2783562f4d?recursive=true&expand=false "HTTP/1.1 200 OK"


Reconstructing (incomplete total...): |          |  0.00B /  0.00B            

Fetching 17 files:   0%|          | 0/17 [00:00<?, ?it/s]

2026-09-25 12:28:09,512 [INFO] HTTP Request: HEAD https://huggingface.co/black-forest-labs/FLUX.2-klein-base-4B/resolve/a3b4f4849157f664bdbc776fd7453c2783562f4d/scheduler/scheduler_config.json "HTTP/1.1 307 Temporary Redirect"
2026-09-25 12:28:09,513 [WARNING] Warning: You are sending unauthenticated requests to the HF Hub. Please set a HF_TOKEN to enable higher rate limits and faster downloads.
2026-09-25 12:28:09,526 [INFO] HTTP Request: HEAD https://huggingface.co/api/resolve-cache/models/black-forest-labs/FLUX.2-klein-base-4B/a3b4f4849157f664bdbc776fd7453c2783562f4d/scheduler%2Fscheduler_config.json "HTTP/1.1 200 OK"
2026-09-25 12:28:09,540 [INFO] HTTP Request: GET https://huggingface.co/api/resolve-cache/models/black-forest-labs/FLUX.2-klein-base-4B/a3b4f4849157f664bdbc776fd7453c2783562f4d/scheduler%2Fscheduler_config.json "HTTP/1.1 200 OK"
2026-09-25 12:28:09,577 [INFO] HTTP Request: HEAD https://huggingface.co/black-forest-labs/FLUX.2-klein-base-4B/resolve/a3b4f4849157f664bdbc77

Loading pipeline components...:   0%|          | 0/5 [00:00<?, ?it/s]

Loading weights:   0%|          | 0/398 [00:00<?, ?it/s]

2026-09-25 12:28:58,827 [INFO] Pipeline successfully loaded.


## Generation Loop
Applying the mask accessory sequentially. Saves the generated image, updates the CSV ledger, and advances the checkpoint file.

In [ ]:
import time
import glob
import os
import torch
import pandas as pd
from PIL import Image, ImageOps

#  prompt
PROMPT = "Add a standard white surgical mask covering the lower half of the face. keep evrything else the same"
TARGET_SIZE = 512
ACCESSORY_TYPE = "mask"

for idx in range(START_INDEX, len(df)):
    row = df.iloc[idx]
    test_hash = row["HASH"]

    # 1. Locate original image
    matches = glob.glob(os.path.join(IMAGES_DIR, "**", f"{test_hash}*"), recursive=True)
    if not matches:
        logger.warning(f"Missing image for hash {test_hash}. Skipping...")
        continue
    source_path = matches[0]

    # 2. Prepare image
    original_image = Image.open(source_path).convert("RGB")
    init_image = ImageOps.pad(
        original_image, (TARGET_SIZE, TARGET_SIZE),
        method=Image.LANCZOS, color=(255, 255, 255), centering=(0.5, 0.5)
    )

    logger.info(f"[{idx+1}/{len(df)}] Generating {ACCESSORY_TYPE} for {test_hash}...")
    t0 = time.time()

    # 3. Generate
    result = pipe(
        image=init_image,
        prompt=PROMPT,
        guidance_scale=4.0,
        num_inference_steps=50,
        generator=torch.Generator(device="cuda").manual_seed(0),
    ).images[0]
    elapsed = time.time() - t0

    # 4. Save Image (Format: hash_mask.png)
    out_filename = f"{test_hash}_{ACCESSORY_TYPE}.png"
    out_filepath = os.path.join(OUTPUT_IMAGES_DIR, out_filename)
    result.save(out_filepath)

    # 5. Update CSV Tracker
    new_row = row.copy()
    new_row["ACCESSORY"] = ACCESSORY_TYPE
    pd.DataFrame([new_row]).to_csv(OUTPUT_CSV, mode='a', header=False, index=False)

    # 6. Update Checkpoint
    with open(CHECKPOINT_FILE, "w") as f:
        f.write(str(idx))

    logger.info(f"Saved {out_filename} in {elapsed:.1f}s")

logger.info("Generation run complete!")

2026-09-25 13:24:15,149 [INFO] [1/720] Generating mask for 09534c3a20eaad55...


  0%|          | 0/50 [00:00<?, ?it/s]

2026-09-25 13:24:40,623 [INFO] Saved 09534c3a20eaad55_mask.png in 25.4s
2026-09-25 13:24:45,968 [INFO] [2/720] Generating mask for 2522757e41af90a0...


  0%|          | 0/50 [00:00<?, ?it/s]

2026-09-25 13:25:10,533 [INFO] Saved 2522757e41af90a0_mask.png in 24.4s
2026-09-25 13:25:10,801 [INFO] [3/720] Generating mask for be2c17990647d063...


...

2026-09-25 18:41:03,014 [INFO] Saved 7de85275e77b2d89_mask.png in 25.0s
2026-09-25 18:41:03,734 [INFO] [719/720] Generating mask for 2d17abef7513b47c...


  0%|          | 0/50 [00:00<?, ?it/s]

2026-09-25 18:41:28,901 [INFO] Saved 2d17abef7513b47c_mask.png in 25.0s
2026-09-25 18:41:29,624 [INFO] [720/720] Generating mask for a42b5980bbe630e5...


  0%|          | 0/50 [00:00<?, ?it/s]

2026-09-25 18:41:54,891 [INFO] Saved a42b5980bbe630e5_mask.png in 25.1s
2026-09-25 18:41:54,892 [INFO] Generation run complete!
